
# Safe City AI | Motorcycle and Rider Head Detection

This notebook implements the first stage of the helmet violation detection module.

### Implemented features
- Motorcycle and person detection using YOLOv8s
- Motorcycle tracking using ByteTrack
- Rider-to-motorcycle association
- Rider head localization using YOLO11n-Pose
- Fallback head localization when facial keypoints are unavailable
- Annotated CCTV video generation

### Next stage
Helmet/no-helmet classification using a custom-trained head classifier.


In [1]:

%pip install -q ultralytics opencv-python-headless tqdm

import cv2
import torch
import numpy as np

from pathlib import Path
from tqdm.auto import tqdm
from ultralytics import YOLO
from google.colab import files
from IPython.display import Video, display

DEVICE = 0 if torch.cuda.is_available() else "cpu"

print("Device:", DEVICE)


     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 46.9/46.9 kB 3.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.4/1.4 MB 50.4 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 58.1/58.1 kB 2.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 96.5/96.5 kB 7.8 MB/s eta 0:00:00
Creating new Ultralytics Settings v0.0.8 file ✅ 
View Ultralytics Settings with 'yolo settings' or at '/root/.config/Ultralytics/settings.json'
Update Settings with 'yolo settings key=value', i.e. 'yolo settings runs_dir=path/to/dir'. For help see https://docs.ultralytics.com/usage/settings.
Device: cpu


## 2. Video Upload, Configuration and Models

This section sets up the CCTV detection pipeline.

- **Video Input:** Upload CCTV footage and configure the output directory.
- **YOLOv8s:** Detects motorcycles and persons with a confidence threshold of 0.30 and inference size of 1280.
- **ByteTrack:** Tracks motorcycles across video frames using unique IDs.
- **YOLO11n-Pose:** Locates riders' heads using facial keypoints, with fallback estimation when needed.
- **Output:** Annotated video showing motorcycle and head bounding boxes with tracking IDs.

**Note:** Helmet classification will be implemented in the next stage.

In [2]:

# Upload CCTV video
uploaded = files.upload()
video_name = next(iter(uploaded))
VIDEO_PATH = str(Path("/content") / video_name)

# Output
OUTPUT_DIR = Path("/content/head_detection")
OUTPUT_DIR.mkdir(parents=True, exist_ok=True)
OUTPUT_VIDEO = str(OUTPUT_DIR / "annotated.mp4")

# Detection settings
MOTORCYCLE_CONF = 0.30
PERSON_CONF = 0.30
DETECTION_SIZE = 1280
MAX_BIKE_AREA_RATIO = 0.08

PERSON_CLASS = 0
MOTORCYCLE_CLASS = 3

# Models
vehicle_model = YOLO("yolov8s.pt")
pose_model = YOLO("yolo11n-pose.pt")

print("Models loaded.")


Saving 1008(2).mp4 to 1008(2).mp4
Models loaded.


## 3. Rider Association

This section associates detected persons with their corresponding motorcycles.

- **Spatial Overlap:** Checks horizontal overlap between person and motorcycle bounding boxes.
- **Position Validation:** Verifies the person's vertical alignment with the motorcycle.
- **Rider Matching:** Selects the closest valid person for each motorcycle.
- **Output:** Matched motorcycle-rider pairs for head localization.

**Note:** Geometric matching helps exclude nearby pedestrians but may not be accurate in crowded scenes.

In [3]:

def associate_rider(person, bike):
    px1, py1, px2, py2 = person
    bx1, by1, bx2, by2 = bike

    bw = max(1, bx2 - bx1)
    bh = max(1, by2 - by1)
    pw = max(1, px2 - px1)

    overlap_x = max(
        0, min(px2, bx2) - max(px1, bx1)
    )

    horizontal_overlap = overlap_x / max(
        1, min(pw, bw)
    )

    if horizontal_overlap < 0.25:
        return False

    if not (
        by1 - 0.40 * bh
        <= py2
        <= by2 + 0.40 * bh
    ):
        return False

    if py1 > by1 + 0.45 * bh:
        return False

    return True


def match_riders(bikes, persons):
    pairs = []
    used = set()

    for bike, track_id in bikes:
        bx1, by1, bx2, by2 = bike
        bike_center = (bx1 + bx2) / 2

        candidates = []

        for i, person in enumerate(persons):
            if i in used:
                continue

            if not associate_rider(person, bike):
                continue

            px1, py1, px2, py2 = person
            person_center = (px1 + px2) / 2

            score = abs(
                person_center - bike_center
            ) / max(1, bx2 - bx1)

            candidates.append((score, i, person))

        if candidates:
            _, i, person = min(candidates)
            used.add(i)
            pairs.append((bike, track_id, person))

    return pairs


## 4. Head Localization

This section identifies and extracts the head region of each matched motorcycle rider.

- **YOLO11n-Pose:** Detects facial keypoints, including the nose, eyes and ears.
- **Head Bounding Box:** Calculates the head region using detected keypoints with additional padding.
- **Fallback Detection:** Estimates the head location from the upper portion of the person's bounding box when keypoints are unavailable.
- **Output:** Head bounding boxes for future helmet/no-helmet classification.

In [4]:

def get_head_box(frame, person):
    H, W = frame.shape[:2]
    px1, py1, px2, py2 = person

    pw = px2 - px1
    ph = py2 - py1

    rx1 = max(0, int(px1 - 0.10 * pw))
    ry1 = max(0, int(py1 - 0.10 * ph))
    rx2 = min(W, int(px2 + 0.10 * pw))
    ry2 = min(H, int(py2 + 0.05 * ph))

    if rx2 <= rx1 or ry2 <= ry1:
        return None, False

    person_crop = frame[ry1:ry2, rx1:rx2]

    result = pose_model.predict(
        person_crop,
        conf=0.20,
        imgsz=640,
        device=DEVICE,
        verbose=False
    )[0]

    if (
        result.keypoints is not None
        and result.boxes is not None
        and len(result.boxes) > 0
    ):
        pose_boxes = result.boxes.xyxy.cpu().numpy()
        keypoints = result.keypoints.data.cpu().numpy()

        target_x = (px1 + px2) / 2 - rx1
        target_y = (py1 + py2) / 2 - ry1

        scores = []

        for pb in pose_boxes:
            cx = (pb[0] + pb[2]) / 2
            cy = (pb[1] + pb[3]) / 2

            scores.append(
                (cx - target_x)**2
                + (cy - target_y)**2
            )

        best = int(np.argmin(scores))
        head_points = keypoints[best][:5]

        if head_points.shape[1] >= 3:
            head_points = head_points[
                head_points[:, 2] >= 0.30
            ]

        if len(head_points) >= 2:
            xs = head_points[:, 0] + rx1
            ys = head_points[:, 1] + ry1

            x_min, x_max = xs.min(), xs.max()
            y_min, y_max = ys.min(), ys.max()

            head_w = x_max - x_min
            head_h = y_max - y_min

            pad_x = max(
                0.6 * head_w, 0.18 * pw, 8
            )
            pad_y = max(
                0.8 * head_h, 0.13 * ph, 8
            )

            box = (
                int(max(0, x_min - pad_x)),
                int(max(0, y_min - 1.25 * pad_y)),
                int(min(W, x_max + pad_x)),
                int(min(H, y_max + 0.65 * pad_y))
            )

            if box[2] > box[0] and box[3] > box[1]:
                return box, True

    # Fallback head box
    box = (
        max(0, int(px1 + 0.10 * pw)),
        max(0, int(py1)),
        min(W, int(px2 - 0.10 * pw)),
        min(H, int(py1 + 0.32 * ph))
    )

    if box[2] <= box[0] or box[3] <= box[1]:
        return None, False

    return box, False


## 5. Process Video and Display Results

This section processes CCTV footage and visualizes motorcycle and rider head detections.

- **Motorcycle Detection:** Detects motorcycles and persons using YOLOv8s.
- **Tracking:** Assigns motorcycle tracking IDs using ByteTrack.
- **Rider Association:** Matches detected persons with their motorcycles.
- **Head Localization:** Identifies rider heads using YOLO11n-Pose or fallback estimation.
- **Visualization:** Draws motorcycle and head bounding boxes with tracking IDs.
- **Output:** Generates and displays the annotated video for verification.

**Note:** Helmet classification will be integrated in the next stage.

In [5]:

cap = cv2.VideoCapture(VIDEO_PATH)

if not cap.isOpened():
    raise RuntimeError("Cannot open video.")

fps = cap.get(cv2.CAP_PROP_FPS) or 25.0
W = int(cap.get(cv2.CAP_PROP_FRAME_WIDTH))
H = int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))
total_frames = int(cap.get(cv2.CAP_PROP_FRAME_COUNT))

if W <= 0 or H <= 0:
    cap.release()
    raise RuntimeError("Invalid video dimensions.")

writer = cv2.VideoWriter(
    OUTPUT_VIDEO,
    cv2.VideoWriter_fourcc(*"mp4v"),
    fps,
    (W, H)
)

if not writer.isOpened():
    cap.release()
    raise RuntimeError("Cannot create output video.")

frame_area = W * H
frame_index = 0
total_heads = 0

try:
    for _ in tqdm(
        range(total_frames),
        desc="Processing CCTV"
    ):
        success, frame = cap.read()

        if not success:
            break

        frame_index += 1
        annotated = frame.copy()

        result = vehicle_model.track(
            frame,
            imgsz=DETECTION_SIZE,
            conf=min(MOTORCYCLE_CONF, PERSON_CONF),
            classes=[PERSON_CLASS, MOTORCYCLE_CLASS],
            tracker="bytetrack.yaml",
            persist=True,
            device=DEVICE,
            verbose=False
        )[0]

        bikes = []
        persons = []

        if result.boxes is not None:
            boxes = result.boxes

            ids = (
                boxes.id.int().cpu().tolist()
                if boxes.id is not None
                else [None] * len(boxes)
            )

            for i, box in enumerate(boxes):
                cls = int(box.cls[0])
                conf = float(box.conf[0])
                coords = tuple(
                    map(int, box.xyxy[0].tolist())
                )

                x1, y1, x2, y2 = coords

                if cls == MOTORCYCLE_CLASS:
                    if conf < MOTORCYCLE_CONF:
                        continue

                    area_ratio = (
                        max(0, x2-x1)
                        * max(0, y2-y1)
                    ) / frame_area

                    if area_ratio <= MAX_BIKE_AREA_RATIO:
                        bikes.append((coords, ids[i]))

                elif cls == PERSON_CLASS:
                    if conf >= PERSON_CONF:
                        persons.append(coords)

        rider_pairs = match_riders(bikes, persons)
        head_count = 0

        for bike, track_id, person in rider_pairs:
            head_box, used_pose = get_head_box(
                frame, person
            )

            if head_box is None:
                continue

            bx1, by1, bx2, by2 = bike
            hx1, hy1, hx2, hy2 = head_box

            head_count += 1
            total_heads += 1

            bike_color = (0, 200, 0)
            head_color = (
                (255, 180, 0)
                if used_pose
                else (0, 165, 255)
            )

            cv2.rectangle(
                annotated,
                (bx1, by1),
                (bx2, by2),
                bike_color,
                2
            )

            cv2.putText(
                annotated,
                f"Motorcycle ID: {track_id}",
                (bx1, max(20, by1 - 8)),
                cv2.FONT_HERSHEY_SIMPLEX,
                0.55,
                bike_color,
                2
            )

            cv2.rectangle(
                annotated,
                (hx1, hy1),
                (hx2, hy2),
                head_color,
                2
            )

            method = "Pose" if used_pose else "Fallback"

            cv2.putText(
                annotated,
                f"Head ({method})",
                (hx1, max(20, hy1 - 8)),
                cv2.FONT_HERSHEY_SIMPLEX,
                0.5,
                head_color,
                2
            )

        status = (
            f"Motorcycles: {len(bikes)} | "
            f"Riders: {len(rider_pairs)} | "
            f"Heads: {head_count}"
        )

        cv2.putText(
            annotated,
            status,
            (20, max(25, H - 25)),
            cv2.FONT_HERSHEY_SIMPLEX,
            0.65,
            (255, 255, 255),
            2
        )

        writer.write(annotated)

finally:
    cap.release()
    writer.release()

print("Frames processed:", frame_index)
print("Total head detections:", total_heads)
print("Output:", OUTPUT_VIDEO)

display(Video(OUTPUT_VIDEO, embed=True, width=900))


Processing CCTV:   0%|          | 0/220 [00:00<?, ?it/s]

requirements: Ultralytics requirement ['lap>=0.5.12'] not found, attempting AutoUpdate...
Using Python 3.13.16 environment at: /usr
Resolved 2 packages in 708ms
Prepared 1 package in 28ms
Installed 1 package in 1ms
 + lap==0.5.13

requirements: AutoUpdate success ✅ 1.0s
WARNING ⚠️ requirements: Restart runtime or rerun command for updates to take effect

Frames processed: 220
Total head detections: 304
Output: /content/head_detection/annotated.mp4


In [6]:
# Download processed CCTV video
from google.colab import files

files.download(OUTPUT_VIDEO)

<IPython.core.display.Javascript object>

<IPython.core.display.Javascript object>